In [0]:
from pyspark.sql import SparkSession
from pyspark.sql.types import *
from pyspark.sql import functions as F

import random
import numpy as np
from datetime import datetime, timedelta

In [0]:
DEMAND_PROFILES = [
    "Stable",
    "Seasonal",
    "Trending",
    "Intermittent",
    "New Launch",
    "Declining"
]

ABC_CLASSES = ["A", "B", "C"]

XYZ_CLASSES = ["X", "Y", "Z"]

weights=[0.2,0.3,0.5]

In [0]:
CONFIG = {

    "DATABASE": "forecast_db",

    "NUM_PRODUCTS": 500,

    "NUM_WEEKS": 104,

    "SEED": 42,

    "START_DATE": "2024-01-01"

}

In [0]:
random.seed(CONFIG["SEED"])

np.random.seed(CONFIG["SEED"])

In [0]:
spark = SparkSession.getActiveSession()

spark.sql(

    f"""

    CREATE DATABASE IF NOT EXISTS

    {CONFIG["DATABASE"]}

    """

)

DataFrame[]

In [0]:
CATEGORIES = [

    "Beverages",

    "Snacks",

    "Dairy",

    "Personal Care",

    "Home Care"

]

BRANDS = [

    "FreshMart",

    "Nova",

    "Prime",

    "Daily"

]

REGIONS = [

    "North",

    "South",

    "East",

    "West"

]

PLANTS = [

    "Plant_A",

    "Plant_B",

    "Plant_C",

    "Plant_D"

]

In [0]:
def generate_products():

    # Initialize the list that will store all product records
    products = []

    for i in range(1, CONFIG["NUM_PRODUCTS"] + 1):

        sku = f"SKU{i:04d}"

        products.append({

            "sku": sku,

            "product_name": f"Product {i}",

            "brand": random.choice(BRANDS),

            "category": random.choice(CATEGORIES),

            "sub_category": "General",

            "uom": "EA",

            "region": random.choice(REGIONS),

            "plant": random.choice(PLANTS),

            "launch_date": datetime(
                2024, 1, 1
            ) + timedelta(
                days=random.randint(0, 365)
            ),

            "lifecycle_stage": random.choice(
                [
                    "Launch",
                    "Growth",
                    "Mature",
                    "Decline"
                ]
            ),

            "demand_profile": random.choices(
                DEMAND_PROFILES,
                weights=[45, 20, 15, 10, 5, 5],
                k=1
            )[0],

            "abc_class": random.choices(
                ABC_CLASSES,
                weights=[20, 30, 50],
                k=1
            )[0],

            "xyz_class": random.choices(
                XYZ_CLASSES,
                weights=[50, 30, 20],
                k=1
            )[0],

            "unit_price": round(
                random.uniform(20, 300),
                2
            )

        })

    return products

In [0]:
product_df = spark.createDataFrame(
    generate_products()
)

product_df.write \
    .mode("overwrite") \
    .option("overwriteSchema", "true") \
    .format("delta") \
    .saveAsTable(f"{CONFIG['DATABASE']}.dim_product")

In [0]:
def generate_calendar():

    calendar = []

    start = datetime.strptime(

        CONFIG["START_DATE"],

        "%Y-%m-%d"

    )

    for week in range(

        1,

        CONFIG["NUM_WEEKS"] + 1

    ):

        d = start + timedelta(

            weeks=week-1

        )

        calendar.append({

            "week_id": week,

            "week_start": d.date(),

            "month": d.month,

            "quarter": (

                d.month-1

            )//3 + 1,

            "year": d.year

        })

    return calendar

In [0]:
product_df = spark.createDataFrame(

    generate_products()

)

calendar_df = spark.createDataFrame(

    generate_calendar()

)

product_df.write.mode(

    "overwrite"

).format(

    "delta"

).saveAsTable(

    f"{CONFIG['DATABASE']}.dim_product"

)

calendar_df.write.mode(

    "overwrite"

).format(

    "delta"

).saveAsTable(

    f"{CONFIG['DATABASE']}.dim_calendar"

)

In [0]:
print("Products")

display(product_df.limit(5))

print("Calendar")

display(calendar_df.limit(5))

Products


brand,category,launch_date,lifecycle_stage,plant,product_name,region,sku,sub_category,unit_price,uom
Nova,Home Care,2024-11-23T00:00:00.000Z,Mature,Plant_C,Product 1,North,SKU0001,General,190.51,EA
Nova,Dairy,2024-11-02T00:00:00.000Z,Growth,Plant_A,Product 2,South,SKU0002,General,156.81,EA
FreshMart,Dairy,2024-01-30T00:00:00.000Z,Launch,Plant_B,Product 3,East,SKU0003,General,265.84,EA
FreshMart,Beverages,2024-09-29T00:00:00.000Z,Launch,Plant_A,Product 4,West,SKU0004,General,55.95,EA
Daily,Home Care,2024-09-27T00:00:00.000Z,Mature,Plant_C,Product 5,South,SKU0005,General,138.48,EA


Calendar


month,quarter,week_id,week_start,year
1,1,1,2024-01-01,2024
1,1,2,2024-01-08,2024
1,1,3,2024-01-15,2024
1,1,4,2024-01-22,2024
1,1,5,2024-01-29,2024


In [0]:
products.append({

    "sku": sku,

    "product_name": f"Product {i}",

    "brand": random.choice(BRANDS),

    "category": random.choice(CATEGORIES),

    "sub_category": "General",

    "uom": "EA",

    "region": random.choice(REGIONS),

    "plant": random.choice(PLANTS),

    "launch_date": datetime(
        2024,1,1
    ) + timedelta(
        days=random.randint(0,365)
    ),

    "lifecycle_stage": random.choice(
        [
            "Launch",
            "Growth",
            "Mature",
            "Decline"
        ]
    ),

    "demand_profile": random.choices(
        DEMAND_PROFILES,
        weights=[45,20,15,10,5,5],
        k=1
    )[0],

    "abc_class": random.choices(
        ABC_CLASSES,
        weights=[20,30,50],
        k=1
    )[0],

    "xyz_class": random.choices(
        XYZ_CLASSES,
        weights=[50,30,20],
        k=1
    )[0],

    "unit_price": round(
        random.uniform(20,300),
        2
    )

})

---------------------------------------------------------------------------
NameError                                 Traceback (most recent call last)
File <command-6906593805385186>, line 1
----> 1 products.append({
      2 
      3     "sku": sku,
      4 
      5     "product_name": f"Product {i}",
      6 
      7     "brand": random.choice(BRANDS),
      8 
      9     "category": random.choice(CATEGORIES),
     10 
     11     "sub_category": "General",
     12 
     13     "uom": "EA",
     14 
     15     "region": random.choice(REGIONS),
     16 
     17     "plant": random.choice(PLANTS),
     18 
     19     "launch_date": datetime(
     20         2024,1,1
     21     ) + timedelta(
     22         days=random.randint(0,365)
     23     ),
     24 
     25     "lifecycle_stage": random.choice(
     26         [
     27             "Launch",
     28             "Growth",
     29             "Mature",
     30             "Decline"
     31         ]
     32     ),
     33 
  

In [0]:
sales_forecast_df = spark.read.format("delta").table("workspace.forecast_db.fact_sales_forecast")
display(sales_forecast_df)

date,store_id,product_id,category,region,inventory_level,units_sold,units_ordered,demand_forecast,price,discount,weather_condition,holiday_promotion,competitor_pricing,seasonality
2023-01-01,S003,P0011,Groceries,North,96,7,144,1.0,57.28,15,Snowy,1,53.64,Spring
2023-01-01,S003,P0012,Toys,East,208,160,144,159.76,68.51,15,Sunny,0,68.36,Winter
2023-01-01,S003,P0013,Electronics,West,397,379,164,390.42,48.36,10,Sunny,1,52.63,Spring
2023-01-01,S003,P0014,Toys,East,463,342,44,337.29,24.04,10,Sunny,1,27.59,Autumn
2023-01-01,S003,P0015,Groceries,North,449,231,73,228.22,77.79,20,Snowy,0,79.07,Winter
2023-01-01,S003,P0016,Clothing,South,185,129,92,134.9,39.72,15,Rainy,0,44.71,Summer
2023-01-01,S003,P0017,Toys,West,476,336,126,351.81,79.87,0,Cloudy,1,79.91,Autumn
2023-01-01,S003,P0018,Clothing,West,178,172,81,179.89,51.0,20,Cloudy,0,48.06,Summer
2023-01-01,S003,P0019,Furniture,South,137,75,29,68.15,49.6,15,Sunny,1,45.42,Summer
2023-01-01,S003,P0020,Electronics,South,258,131,152,145.92,44.65,20,Snowy,1,41.05,Autumn


In [0]:
forecast_metrics_df = spark.read.format("delta").table("workspace.forecast_db.vw_forecast_metrics")
display(forecast_metrics_df)

date,store_id,product_id,category,region,inventory_level,units_sold,units_ordered,demand_forecast,price,discount,weather_condition,holiday_promotion,competitor_pricing,seasonality,forecast_accuracy,forecast_bias
2023-01-01,S003,P0011,Groceries,North,96,7,144,1.0,57.28,15,Snowy,1,53.64,Spring,14.29,-85.71
2023-01-01,S003,P0012,Toys,East,208,160,144,159.76,68.51,15,Sunny,0,68.36,Winter,99.85,-0.15
2023-01-01,S003,P0013,Electronics,West,397,379,164,390.42,48.36,10,Sunny,1,52.63,Spring,96.99,3.01
2023-01-01,S003,P0014,Toys,East,463,342,44,337.29,24.04,10,Sunny,1,27.59,Autumn,98.62,-1.38
2023-01-01,S003,P0015,Groceries,North,449,231,73,228.22,77.79,20,Snowy,0,79.07,Winter,98.8,-1.2
2023-01-01,S003,P0016,Clothing,South,185,129,92,134.9,39.72,15,Rainy,0,44.71,Summer,95.43,4.57
2023-01-01,S003,P0017,Toys,West,476,336,126,351.81,79.87,0,Cloudy,1,79.91,Autumn,95.29,4.71
2023-01-01,S003,P0018,Clothing,West,178,172,81,179.89,51.0,20,Cloudy,0,48.06,Summer,95.41,4.59
2023-01-01,S003,P0019,Furniture,South,137,75,29,68.15,49.6,15,Sunny,1,45.42,Summer,90.87,-9.13
2023-01-01,S003,P0020,Electronics,South,258,131,152,145.92,44.65,20,Snowy,1,41.05,Autumn,88.61,11.39
